# Generate Your First Synthetic Dataset in Python

In this notebook, you will learn how to create a simple synthetic tabular dataset as well as perform basic structural and distributional checks to compare it with the real data. The following steps will be followed:

**In this notebook, we will:**
1. Explore the real **Abalone** dataset (EDA)
2. Train a generative model using `ydata-sdk`. 
3. The trained model will allows us to create a synthetic replica of the original dataset.
4. Validate synthetic data quality with a side-by-side comparison with the profiling.

> **Dataset:** [Abalone — UCI Machine Learning Repository](https://archive.ics.uci.edu/dataset/1/abalone)  
> License: CC BY 4.0

## 0. Setup

Install the required libraries if you haven't already.

In [ ]:
# Install required packages
# Run this cell once, then restart the kernel
!pip install -q ydata-sdk

## 1. Load & Explore the Real Data

Before generating anything synthetic, we need to understand the real dataset.

The Abalone dataset contains physical measurements of abalone, a type of sea snail, collected to predict age without the time-consuming process of counting shell rings under a microscope. It has 8 physical features, one categorical column, and the target variable Rings, which is a proxy for age.

In [1]:
import pandas as pd 

# Load the pre-combined Wine Quality dataset
df = pd.read_csv("data/abalone.csv")

print(f"Dataset loaded: {df.shape[0]:,} rows × {df.shape[1]} columns")

Dataset loaded: 4,177 rows × 9 columns


In [2]:
# First look at the data
df.head()

,Sex,Length,Diameter,Height,Whole_weight,Shucked_weight,Viscera_weight,Shell_weight,Rings
0,M,0.455,0.365,0.095,0.5140,0.2245,0.1010,0.150,15
1,M,0.350,0.265,0.090,0.2255,0.0995,0.0485,0.070,7
2,F,0.530,0.420,0.135,0.6770,0.2565,0.1415,0.210,9
3,M,0.440,0.365,0.125,0.5160,0.2155,0.1140,0.155,10
4,I,0.330,0.255,0.080,0.2050,0.0895,0.0395,0.055,7


## 2. Explore Distributions (EDA)

Exploratory Data Analysis (EDA) helps us **catch potential data quality issues** and **understand variable relationships** before we attempt to replicate them in synthetic data.

We'll look at:
- A **categorical variable** — `sex` (red vs. white)
- A **numerical variable** — `length` content

In [3]:
from ydata.profiling import ProfileReport

report = ProfileReport(df, title='Abalone measures EDA')
report

INFO: 2026-08-12 13:26:31,121 Using device of type: cpu


Summarize dataset:   0%|          | 0/5 [00:00<?, ?it/s]


100%|██████████████████████████████████████████| 9/9 [00:00<00:00, 1304.74it/s]


Generate report structure:   0%|          | 0/1 [00:00<?, ?it/s]

Render HTML:   0%|          | 0/1 [00:00<?, ?it/s]

### 📌 EDA Key Takeaways

| Finding | Detail |
|---|---|
| **Shape** | 4,177 rows × 9 columns (7 continuous measurements + Sex + Rings) |
| **Missing values** | None — dataset is clean |
| **Feature types** | 7 continuous numeric features + 1 categorical (Sex) + 1 integer target (Rings) |
| **Sex balance** | ~33% male, ~33% female, ~33% infant — well balanced across the three classes |
| **Rings** | Right-skewed; most abalones have 7–12 rings, with a long tail up to 29 |
| **Physical features** | Highly correlated with each other — length, diameter, and all weight columns move together |
| **Height** | Near-normal but with a few extreme outliers worth monitoring in the synthetic output |

All of these patterns are things our synthetic model will need to learn and reproduce.

## 3. Train a Generative Model

Now that we understand our data, we can train a generative model using `ydata-sdk`.

The `RegularSynthesizer` is designed for **standard tabular datasets** — exactly what we have here. It learns the statistical patterns of your data (distributions, correlations, data types) and uses them to generate new realistic rows.

```
Real data  →  fit()  →  Learned patterns  →  sample()  →  Synthetic data
```

In [4]:
from ydata.dataset import Dataset
from ydata.metadata import Metadata
from ydata.synthesizers import RegularSynthesizer

dataset = Dataset(df)
metadata = Metadata(dataset)

# Instantiate the synthesizer
synthesizer = RegularSynthesizer()

# Train the generative model on our real data
# This step learns the statistical structure of the dataset
synthesizer.fit(dataset, 
                metadata=metadata)

print("Model training complete ✓")

Done:  80%|████████████████████████████       | 4/5 [00:00<00:00, 129.31step/s]

Validate the segmentation strategy.
INFO: 2026-08-12 13:28:38,997 [SYNTHESIZER] - Number columns considered for synth: 9


INFO: 2026-08-12 13:28:39,383 [SYNTHESIZER] - Starting the synthetic data modeling process over 1x1 blocks.
INFO: 2026-08-12 13:28:39,385 [SYNTHESIZER] - Preprocess segment
INFO: 2026-08-12 13:28:39,388 [SYNTHESIZER] - Synthesizer init.
INFO: 2026-08-12 13:28:39,388 [SYNTHESIZER] - Processing the data prior fitting the synthesizer.
Model training complete ✓


In [5]:
# Save the trained model
synthesizer.save('wine_synthesizer.pkl')

## 4. Generate Synthetic Data

Once the model is trained, generating synthetic data is straightforward.  
We'll generate the **same number of rows as the original dataset** to make comparisons easier — but you can request as many rows as you need.

In [6]:
# Generate the same number of rows as the real dataset
n_samples = dataset.nrows

df_synthetic = synthesizer.sample(n_samples=n_samples)

print(f"Synthetic dataset shape: {df_synthetic.nrows,} rows × {df_synthetic.ncols} columns")
df_synthetic.head()

INFO: 2026-08-12 13:28:41,357 [SYNTHESIZER] - Start generating model samples.
INFO: 2026-08-12 13:28:41,494 [SYNTHESIZER] - Postprocessing.
INFO: 2026-08-12 13:28:41,495 [SYNTHESIZER] - Numerical clipping
INFO: 2026-08-12 13:28:41,502 let write into the connector None
INFO: 2026-08-12 13:28:41,502 using kwargs {}
Synthetic dataset shape: (4177,) rows × 9 columns


,Sex,Length,Diameter,Height,Whole_weight,Shucked_weight,Viscera_weight,Shell_weight,Rings
0,F,0.410,0.325,0.105,0.3555,0.1405,0.0630,0.1100,12
1,M,0.710,0.565,0.200,2.2100,1.3510,0.3725,0.5030,11
2,F,0.400,0.320,0.115,0.3870,0.1540,0.1025,0.0985,11
3,I,0.620,0.480,0.180,1.1785,0.4675,0.2655,0.3945,11
4,M,0.645,0.520,0.175,1.5365,0.7035,0.3515,0.3990,14


## 5. Validate: Real vs. Synthetic Comparison

The easiest way to validate the quality of generated data is a **side-by-side comparison** — real vs. synthetic.

We'll use the `profiling` again, to generate a comprehensive comparison report.  

> 🔵 **Blue** = Real data &nbsp;&nbsp;&nbsp; 🔴 **Red** = Synthetic data

In [8]:
# Profile the real dataset
profile_real = ProfileReport(
    df,
    title="Real Abalone Quality Data",
    explorative=True,
    minimal=False
)

# Profile the synthetic dataset
profile_synthetic = ProfileReport(
    df_synthetic,
    title="Synthetic Abalone Quality Data",
    explorative=True,
    minimal=False
)

In [9]:
# Generate the side-by-side comparison report
comparison_report = profile_real.compare(profile_synthetic)
comparison_report

Summarize dataset:   0%|          | 0/5 [00:00<?, ?it/s]


100%|██████████████████████████████████████████| 9/9 [00:00<00:00, 1340.89it/s]


Summarize dataset:   0%|          | 0/5 [00:00<?, ?it/s]


100%|███████████████████████████████████████████| 9/9 [00:00<00:00, 505.76it/s]


Generate report structure:   0%|          | 0/1 [00:00<?, ?it/s]

Render HTML:   0%|          | 0/1 [00:00<?, ?it/s]

In [10]:
# Save as an interactive HTML file
comparison_report.to_file("wine_quality_real_vs_synthetic.html")
print("Comparison report saved → wine_quality_real_vs_synthetic.html ✓")

Export report to file:   0%|          | 0/1 [00:00<?, ?it/s]

Comparison report saved → wine_quality_real_vs_synthetic.html ✓


### 📌 What to look for in the comparison report

| Check | What good looks like |
|---|---|
| **Column statistics** | Mean, std, min, max should be close between real and synthetic |
| **Distributions** | Histogram shapes should match — same peaks, tails, and spread |
| **Categorical balance** | `Sex` proportions (~33% each for M / F / I) should be preserved |
| **Correlations** | The strong correlation pattern across physical measurements should be similar |
| **Rings distribution** | Right-skewed shape with the same tail length should be reproduced |
| **Missing values** | Synthetic data should also have none |

## ✅ Summary

In this notebook you:

1. **Loaded** the real Abalone dataset and explored its structure
2. **Performed EDA** to understand distributions and catch any data quality issues
3. **Trained** a `RegularSynthesizer` generative model with `ydata-sdk`
4. **Generated** a synthetic replica with the same number of rows
5. **Validated** the quality with a side-by-side profiling report.